# Data Analytics in Supply Chain Management
## Dataset 3 — Exploratory Data Analysis (EDA) for Retail Demand (Units Sold) Regression

**Scenario.** We are part of the analytics team of a retail chain with five stores. The replenishment team wants to know, for every store–product–day, how many units are likely to be sold, so that inventory levels and purchase orders can be planned better. The goal is not only an accurate prediction, but also an understanding of which **inventory, pricing, promotion, product, location, and external (weather/season) factors** are associated with high or low sales.

**Dataset.** `retail_store_inventory_data.csv` — daily store–product observations (73,100 rows, 15 columns). The dependent variable (target) is **`Units Sold`**.

According to the data description, the dataset contains retail store inventory information (product categories, stock levels, pricing, and sales data) and is intended for inventory-turnover, demand-forecasting, and revenue analyses. It is described as already cleaned and structured.

**Scope of this notebook.** This notebook performs **EDA only**:

- no rows or columns are removed from the dataset,
- no values are imputed, corrected, or transformed in `df`,
- no models are trained.

Any temporary sampling or filtering (for example `df.sample()` inside a plotting cell) happens on a **copy used only for the chart**; the original `df` is never changed. The last cell verifies this.

### Feature dictionary

| Feature | Type | Description |
|---|---|---|
| `Date` | Date | Calendar day of the observation (2022-01-01 to 2024-01-01). Can be used to derive calendar features. |
| `Store ID` | Categorical | Identifier of one of 5 stores (S001–S005). Useful for grouping or store-level diagnostics. |
| `Product ID` | Categorical | Identifier of one of 20 products (P0001–P0020). |
| `Category` | Categorical | Product category: Clothing, Electronics, Furniture, Groceries, or Toys. |
| `Region` | Categorical | Region of the store: East, North, South, or West. |
| `Inventory Level` | Integer | Stock available for the product in the store on that day. |
| `Units Sold` | Integer | Units sold on that day. **Dependent variable to be predicted.** |
| `Units Ordered` | Integer | Units ordered (replenishment order quantity). |
| `Demand Forecast` | Numeric | Predicted demand for the product on that day (an existing forecast). |
| `Price` | Numeric | Selling price of the product. |
| `Discount` | Integer | Discount in percent (0, 5, 10, 15, 20). |
| `Weather Condition` | Categorical | Weather on that day: Sunny, Rainy, Cloudy, or Snowy. |
| `Holiday/Promotion` | Integer (0/1) | 1 if the day is a holiday or the product is on promotion, otherwise 0. |
| `Competitor Pricing` | Numeric | Price of the same/similar product at a competitor. |
| `Seasonality` | Categorical | Season label: Spring, Summer, Autumn, or Winter. |

**Feature groups used in the interpretation:**

- **Inventory & replenishment:** `Inventory Level`, `Units Ordered`
- **Existing forecast:** `Demand Forecast`
- **Pricing & promotion:** `Price`, `Discount`, `Competitor Pricing`, `Holiday/Promotion`
- **Product & location:** `Store ID`, `Product ID`, `Category`, `Region`
- **External factors:** `Weather Condition`, `Seasonality`
- **Time:** `Date`

> **Note on `Demand Forecast`.** An existing forecast is a special feature: if it was produced *after* the sales were known, or is itself a model of `Units Sold`, it can leak target information into a model. The EDA below checks how closely it follows the target.

### EDA workflow used in this notebook

**0. Setup → 1. Configure & load data → 2. Understand the big picture → 3. Check data quality → 4. Univariate analysis → 5. Target-focused analysis → 6. Multivariate analysis → 7. Association between categorical variables (Chi-square & Cramér's V) → 8. Summary of findings**

The code is taken from the two course notebooks (`EDA_Plotly_Python_3_9_23.ipynb` and `Cramers.ipynb`) and only re-configured for this dataset.

> **Recommended workflow:** Run the notebook from top to bottom (*Kernel → Restart & Run All*).

## 0. Setup — install packages and import libraries

This is the **single cell** for installing packages and importing every library used in the notebook.

- The first time, keep `INSTALL_PACKAGES = True`. On Python 3.9 the cell installs the recommended, pinned package stack from the EDA template plus `researchpy` (used in `Cramers.ipynb`); on newer Python versions it installs the latest compatible versions (with `pandas<3`, because `researchpy` does not work with pandas 3).
- **Before the first run**, the selected kernel must contain `ipykernel` (VS Code asks for this automatically). In a terminal: `python -m pip install ipykernel`.
- If an installation **changed** package versions, restart the kernel once (*Kernel → Restart*) and run the notebook again.
- Afterwards you can set `INSTALL_PACKAGES = False` to skip the installation step.
- If you need another package later, add it to the `%pip install` line.

Recommended versions:

```text
numpy==1.26.4  pandas==2.2.3  scipy==1.13.1  plotly==5.24.1
nbformat==5.10.4  ipython==8.18.1  openpyxl==3.1.5  researchpy==0.3.6
```

In [1]:
# -----------------------------------------------------------------------------
# PACKAGE INSTALLATION (run once) + CORE IMPORTS
# -----------------------------------------------------------------------------

INSTALL_PACKAGES = False   # set to False after the first successful installation

import sys

if INSTALL_PACKAGES:
    if sys.version_info[:2] == (3, 9):
        # Course environment (Python 3.9.23): pinned, tested versions.
        %pip install numpy==1.26.4 pandas==2.2.3 scipy==1.13.1 plotly==5.24.1 nbformat==5.10.4 ipython==8.18.1 ipykernel openpyxl==3.1.5 researchpy==0.3.6
    else:
        # Newer Python versions: latest compatible versions.
        # pandas is kept below 3.0 because researchpy does not work with pandas 3.
        %pip install numpy scipy "pandas<3" plotly nbformat ipython ipykernel openpyxl researchpy

# Standard-library tools
from pathlib import Path

# Data manipulation
import numpy as np
import pandas as pd
from pandas import read_csv

# Interactive visualization with Plotly
import plotly
import plotly.express as px
import plotly.graph_objects as go
import plotly.figure_factory as ff
import plotly.io as pio
from plotly.subplots import make_subplots

# Statistical utilities
from scipy.cluster import hierarchy
from scipy.stats import gaussian_kde, zscore
import researchpy   # Chi-square test and Cramer's V (from Cramers.ipynb)

# Jupyter display helpers
from IPython.display import HTML, display

# Make pandas tables easier to read in Jupyter.
pd.set_option("display.max_columns", 100)
pd.set_option("display.float_format", lambda x: f"{x:,.3f}")

# Show the environment so it can be reported when troubleshooting.
print("Python version :", sys.version.split()[0])
print("pandas version :", pd.__version__)
print("NumPy version  :", np.__version__)
print("Plotly version :", plotly.__version__)

# Python 3.9.x is the intended course environment.
if sys.version_info[:2] != (3, 9):
    print("NOTE: This notebook is designed for Python 3.9.23; your kernel uses a different version.")

# Use Plotly's connected notebook renderer when the Jupyter stack supports it.
PLOTLY_RENDERER = "notebook_connected"

# Common toolbar settings for all charts.
PLOTLY_CONFIG = {
    "displaylogo": False,
    "responsive": True,
    "scrollZoom": False,
}


def show_plotly(fig):
    """Display a Plotly figure robustly inside Jupyter.

    Normal path
    -----------
    Use Plotly's Jupyter renderer, which is compact and fully interactive.

    Fallback path
    -------------
    Some environments have Plotly installed but an old/missing `nbformat`,
    producing the error:
        'Mime type rendering requires nbformat>=4.2.0 ...'

    If that specific renderer problem occurs, render self-contained HTML
    instead. This keeps the figure interactive and avoids the MIME renderer.
    """
    try:
        fig.show(renderer=PLOTLY_RENDERER, config=PLOTLY_CONFIG)
    except ValueError as exc:
        message = str(exc).lower()
        if "nbformat" not in message and "mime type rendering" not in message:
            raise

        print(
            "Plotly Jupyter renderer is unavailable; using the interactive "
            "HTML fallback for this figure."
        )

        # include_plotlyjs=True embeds plotly.js directly in the HTML output.
        # Therefore the fallback does not depend on nbformat or internet access.
        interactive_html = fig.to_html(
            full_html=False,
            include_plotlyjs=True,
            config=PLOTLY_CONFIG,
        )
        display(HTML(interactive_html))

Python version : 3.12.10
pandas version : 2.2.3
NumPy version  : 2.2.6
Plotly version : 5.24.1
NOTE: This notebook is designed for Python 3.9.23; your kernel uses a different version.


**Plotly interaction tips:** hover to inspect values, drag to zoom, double-click to reset, and click legend entries to hide/show groups.

## 1. Configure and load the dataset

### 1.1 Dataset settings

All dataset-specific settings are kept in this one cell.

- `DATASET_PATH` assumes the CSV file is in the **same folder** as this notebook. If it is stored elsewhere, change the path (e.g. `Path("../Datasets/retail_store_inventory_data.csv")`).
- `READ_OPTIONS` asks pandas to read `Date` as a real date. This only changes the **data type**; no values are changed or removed.
- `TARGET_COLUMN` is the regression target. `GROUP_COLUMN` (`Category`) and `HUE_COLUMN` (`Region`) are the categorical variables used to split and colour the charts.
- `EXCLUDE_COLUMNS` lists columns that should not be plotted automatically: the date. It remains in `df`.
- `MAX_PLOT_COLUMNS = 8` makes the automatic loops cover **all** 8 numerical variables (including the target).
- The dataset has **73,100 rows**. Interactive scatter-type charts draw one marker per row, so `SCATTER_MAX_ROWS` limits those charts to a random sample (same idea as `PAIRPLOT_MAX_ROWS` in the template). Distribution charts, statistics, and correlations always use **all** rows.

In [2]:
# -----------------------------------------------------------------------------
# DATASET CONFIGURATION
# -----------------------------------------------------------------------------

# Path to the dataset. Relative paths are interpreted from the notebook folder.
DATASET_PATH = Path("../data/retail_store_inventory_data.csv")

# Optional keyword arguments passed to the file reader.
# parse_dates converts Date from text to a datetime type (no rows are removed).
READ_OPTIONS = {"parse_dates": ["Date"]}

# Semantic roles used in selected visualizations.
TARGET_COLUMN = "Units Sold"   # dependent variable of the regression task
GROUP_COLUMN = "Category"      # main grouping variable
HUE_COLUMN = "Region"          # second categorical dimension (colour)

# Columns that should not be plotted automatically (date).
# They are NOT removed from the dataset.
EXCLUDE_COLUMNS = ["Date"]

# Plot all 8 numerical variables in the automatic loops.
MAX_PLOT_COLUMNS = 8

# Interactive scatter matrices can become slow with very large datasets.
PAIRPLOT_MAX_ROWS = 1500

# Scatter and bubble charts draw one marker per row; with 73,100 rows they are
# sampled for the visualization only (the original df is not changed).
SCATTER_MAX_ROWS = 5000

# Missing-value heatmaps can also become heavy because each row becomes a tile.
MISSING_HEATMAP_MAX_ROWS = 2000

### 1.2 Reusable data-loading function

This function chooses the correct pandas reader from the file extension (CSV/TXT, Excel, Parquet, JSON).

In [3]:
def load_dataset(path, read_options=None):
    """Load a dataset based on its file extension."""
    path = Path(path)
    read_options = read_options or {}

    # Give a clear message if the file path is incorrect.
    if not path.exists():
        raise FileNotFoundError(
            f"Dataset not found: {path.resolve()}\n"
            "Update DATASET_PATH in the configuration cell."
        )

    # Select a pandas reader according to the file extension.
    suffix = path.suffix.lower()

    if suffix in {".csv", ".txt"}:
        return pd.read_csv(path, **read_options)
    if suffix in {".xlsx", ".xls"}:
        return pd.read_excel(path, **read_options)
    if suffix == ".parquet":
        return pd.read_parquet(path, **read_options)
    if suffix == ".json":
        return pd.read_json(path, **read_options)

    raise ValueError(
        f"Unsupported file type: {suffix}. "
        "Use CSV, TXT, Excel, Parquet, or JSON."
    )

In [4]:
# Load the dataset using the configuration above.
df = load_dataset(DATASET_PATH, READ_OPTIONS)

# Remember the original size so we can prove at the end that no data was removed.
ORIGINAL_SHAPE = df.shape

# Show the first five rows to confirm that the file was loaded correctly.
df.head()

,Date,Store ID,Product ID,Category,Region,Inventory Level,Units Sold,Units Ordered,Demand Forecast,Price,Discount,Weather Condition,Holiday/Promotion,Competitor Pricing,Seasonality
0,2022-01-01,S001,P0001,Groceries,North,231,127,55,135.470,33.500,20,Rainy,0,29.690,Autumn
1,2022-01-01,S001,P0002,Toys,South,204,150,66,144.040,63.010,20,Sunny,0,66.160,Autumn
2,2022-01-01,S001,P0003,Toys,West,102,65,51,74.020,27.990,10,Sunny,1,31.320,Summer
3,2022-01-01,S001,P0004,Toys,North,469,61,164,62.180,32.720,10,Cloudy,1,34.740,Autumn
4,2022-01-01,S001,P0005,Electronics,East,166,14,135,9.260,73.640,0,Sunny,0,68.950,Summer


### 1.3 Automatically identify variable types

Numerical and categorical variables are derived from the dataset itself. `Store ID` and `Product ID` are kept as categorical variables because they are useful for store- and product-level diagnostics. `Discount` (5 levels) and `Holiday/Promotion` (0/1) are stored as integers and are therefore treated as numerical here; their discrete nature is taken into account when interpreting the charts. We also create `feature_columns`: all numerical variables **except** the target.

In [5]:
# Keep only exclusion names that actually exist in the current dataset.
existing_exclusions = [col for col in EXCLUDE_COLUMNS if col in df.columns]

# Numerical variables: integer/float columns, excluding configured ID/date fields.
numeric_columns = [
    col for col in df.select_dtypes(include="number").columns
    if col not in existing_exclusions
]

# Categorical variables: text, category, or boolean columns.
categorical_columns = [
    col for col in df.select_dtypes(exclude="number").columns
    if col not in existing_exclusions
]

# Limit automatic loops so the notebook remains readable with wide datasets.
numeric_plot_columns = numeric_columns[:MAX_PLOT_COLUMNS]
categorical_plot_columns = categorical_columns[:MAX_PLOT_COLUMNS]

# Numerical predictors only (target excluded) — used in the target-focused section.
feature_columns = [col for col in numeric_columns if col != TARGET_COLUMN]

print(f"Rows: {len(df):,}")
print(f"Columns: {df.shape[1]}")
print(f"Numerical columns ({len(numeric_columns)}): {numeric_columns}")
print(f"Categorical columns ({len(categorical_columns)}): {categorical_columns}")
print(f"Numerical features without target ({len(feature_columns)}): {feature_columns}")

Rows: 73,100
Columns: 15
Numerical columns (8): ['Inventory Level', 'Units Sold', 'Units Ordered', 'Demand Forecast', 'Price', 'Discount', 'Holiday/Promotion', 'Competitor Pricing']
Categorical columns (6): ['Store ID', 'Product ID', 'Category', 'Region', 'Weather Condition', 'Seasonality']
Numerical features without target (7): ['Inventory Level', 'Units Ordered', 'Demand Forecast', 'Price', 'Discount', 'Holiday/Promotion', 'Competitor Pricing']


### 1.4 Resolve column roles safely

The helper uses the preferred column when it exists; otherwise it falls back to an available column.

In [6]:
def choose_column(preferred, candidates, fallback_position=0):
    """Return preferred column if available, otherwise a fallback candidate."""
    if preferred in df.columns:
        return preferred
    if len(candidates) > fallback_position:
        return candidates[fallback_position]
    return None

# Resolve the configured roles for the current dataset.
group_col = choose_column(GROUP_COLUMN, categorical_columns, 0)
hue_col = choose_column(HUE_COLUMN, categorical_columns, 1)
target_col = TARGET_COLUMN if TARGET_COLUMN in df.columns else None

print("Resolved plotting roles:")
print("  Group column :", group_col)
print("  Hue column   :", hue_col)
print("  Target column:", target_col)

Resolved plotting roles:
  Group column : Category
  Hue column   : Region
  Target column: Units Sold


## 2. Step 1 — Understand the big picture

Before drawing many charts, ask:

- How large is the dataset?
- What does one row represent? *(Here: one product in one store on one day.)*
- Which variables are numerical or categorical?
- Are values missing — including in the target?
- Are the magnitudes and ranges plausible for a retail store?

### 2.1 Dataset dimensions

In [7]:
rows, columns = df.shape
print(f"The dataset contains {rows:,} rows and {columns} columns.")

The dataset contains 73,100 rows and 15 columns.


### 2.2 Inspect example records

Looking at both the first rows and a random sample helps detect formatting issues quickly.

In [8]:
display(df.head())

# Random rows can reveal patterns that are not visible at the top of the file.
# random_state makes the sample reproducible.
display(df.sample(min(5, len(df)), random_state=42))

,Date,Store ID,Product ID,Category,Region,Inventory Level,Units Sold,Units Ordered,Demand Forecast,Price,Discount,Weather Condition,Holiday/Promotion,Competitor Pricing,Seasonality
0,2022-01-01,S001,P0001,Groceries,North,231,127,55,135.470,33.500,20,Rainy,0,29.690,Autumn
1,2022-01-01,S001,P0002,Toys,South,204,150,66,144.040,63.010,20,Sunny,0,66.160,Autumn
2,2022-01-01,S001,P0003,Toys,West,102,65,51,74.020,27.990,10,Sunny,1,31.320,Summer
3,2022-01-01,S001,P0004,Toys,North,469,61,164,62.180,32.720,10,Cloudy,1,34.740,Autumn
4,2022-01-01,S001,P0005,Electronics,East,166,14,135,9.260,73.640,0,Sunny,0,68.950,Summer


,Date,Store ID,Product ID,Category,Region,Inventory Level,Units Sold,Units Ordered,Demand Forecast,Price,Discount,Weather Condition,Holiday/Promotion,Competitor Pricing,Seasonality
66127,2023-10-24,S002,P0008,Electronics,North,225,138,144,139.310,40.470,0,Snowy,1,41.970,Winter
43485,2023-03-11,S005,P0006,Toys,North,200,105,119,117.550,18.650,15,Cloudy,1,16.650,Spring
34304,2022-12-10,S001,P0005,Clothing,East,145,70,137,78.510,20.330,15,Snowy,0,18.040,Winter
34317,2022-12-10,S001,P0018,Electronics,West,350,105,157,103.110,98.650,15,Sunny,0,95.430,Spring
38631,2023-01-22,S002,P0012,Groceries,North,145,76,145,92.470,10.040,20,Sunny,0,13.010,Winter


### 2.3 Data types and non-null counts

`info()` quickly reveals suspicious types (e.g. a quantity stored as text) and columns with fewer non-null values than rows.

In [9]:
df.info()

<class 'pandas.core.frame.DataFrame'>
RangeIndex: 73100 entries, 0 to 73099
Data columns (total 15 columns):
 #   Column              Non-Null Count  Dtype         
---  ------              --------------  -----         
 0   Date                73100 non-null  datetime64[ns]
 1   Store ID            73100 non-null  object        
 2   Product ID          73100 non-null  object        
 3   Category            73100 non-null  object        
 4   Region              73100 non-null  object        
 5   Inventory Level     73100 non-null  int64         
 6   Units Sold          73100 non-null  int64         
 7   Units Ordered       73100 non-null  int64         
 8   Demand Forecast     73100 non-null  float64       
 9   Price               73100 non-null  float64       
 10  Discount            73100 non-null  int64         
 11  Weather Condition   73100 non-null  object        
 12  Holiday/Promotion   73100 non-null  int64         
 13  Competitor Pricing  73100 non-null  float64   

### 2.4 Descriptive statistics

Using `include="all"` summarizes numerical, categorical, and date columns together. Compare `min`/`max` with the feature dictionary: are any values implausible from a retail perspective (e.g. a **negative** demand forecast, or more units sold than were in stock)?

In [10]:
display(df.describe(include="all").T)

,count,unique,top,freq,mean,min,25%,50%,75%,max,std
Date,73100,NaN,NaN,NaN,2022-12-31 23:59:59.999999744,2022-01-01 00:00:00,2022-07-02 00:00:00,2023-01-01 00:00:00,2023-07-03 00:00:00,2024-01-01 00:00:00,NaN
Store ID,73100,5,S001,14620,NaN,NaN,NaN,NaN,NaN,NaN,NaN
Product ID,73100,20,P0001,3655,NaN,NaN,NaN,NaN,NaN,NaN,NaN
Category,73100,5,Furniture,14699,NaN,NaN,NaN,NaN,NaN,NaN,NaN
Region,73100,4,East,18349,NaN,NaN,NaN,NaN,NaN,NaN,NaN
Inventory Level,"73,100.000",NaN,NaN,NaN,274.470,50.000,162.000,273.000,387.000,500.000,129.950
Units Sold,"73,100.000",NaN,NaN,NaN,136.465,0.000,49.000,107.000,203.000,499.000,108.919
Units Ordered,"73,100.000",NaN,NaN,NaN,110.004,20.000,65.000,110.000,155.000,200.000,52.277
Demand Forecast,"73,100.000",NaN,NaN,NaN,141.495,-9.990,53.670,113.015,208.053,518.550,109.254
Price,"73,100.000",NaN,NaN,NaN,55.135,10.000,32.650,55.050,77.860,100.000,26.022


### 2.5 Missing-value summary

A missing value may mean *unknown*, *not applicable*, *not recorded*, or a processing error. Missing values in the **target** are especially important because such rows cannot be used directly to train a supervised model. Anything found is only reported, not removed.

In [11]:
# Count and percentage of missing values for every column.
missing_summary = pd.DataFrame({
    "missing_count": df.isna().sum(),
    "missing_percent": df.isna().mean() * 100,
})

# Show columns with most missing values first.
missing_summary = missing_summary.sort_values("missing_percent", ascending=False)
display(missing_summary)

,missing_count,missing_percent
Date,0,0.000
Store ID,0,0.000
Product ID,0,0.000
Category,0,0.000
Region,0,0.000
Inventory Level,0,0.000
Units Sold,0,0.000
Units Ordered,0,0.000
Demand Forecast,0,0.000
Price,0,0.000


### 2.6 Interactive missing-value heatmap

The heatmap shows **where** values are missing. For large datasets, rows are sampled only for the visualization; the original dataset remains unchanged.

In [12]:
if df.isna().sum().sum() == 0:
    print("No missing values found in the dataset.")
else:
    # Sample rows only when necessary to keep the interactive heatmap responsive.
    heatmap_df = df
    if len(df) > MISSING_HEATMAP_MAX_ROWS:
        heatmap_df = df.sample(MISSING_HEATMAP_MAX_ROWS, random_state=42)
        print(
            f"Heatmap uses a random sample of {MISSING_HEATMAP_MAX_ROWS:,} rows "
            f"from {len(df):,} total rows."
        )

    # Plotly displays 1 for missing and 0 for present.
    missing_matrix = heatmap_df.isna().astype(int)

    fig = px.imshow(
        missing_matrix,
        aspect="auto",
        labels={"x": "Variable", "y": "Row", "color": "Missing?"},
        title="Missing Values Heatmap",
    )
    fig.update_yaxes(showticklabels=False)
    fig.update_layout(height=500)
    show_plotly(fig)

No missing values found in the dataset.


### 2.7 Interactive bar chart of missing values

In [13]:
missing_counts = df.isna().sum()
missing_counts = missing_counts[missing_counts > 0].sort_values(ascending=False)

if missing_counts.empty:
    print("No missing values found in the dataset.")
else:
    missing_plot_df = missing_counts.rename("Missing values").reset_index()
    missing_plot_df.columns = ["Variable", "Missing values"]

    fig = px.bar(
        missing_plot_df,
        x="Variable",
        y="Missing values",
        title="Missing Values per Column",
        text="Missing values",
    )
    fig.update_layout(xaxis_tickangle=-45)
    show_plotly(fig)

No missing values found in the dataset.


### 2.8 Interactive missingness dendrogram

Clusters **columns** with similar missing-value patterns. If two variables are missing in the same rows, they may share a common cause (e.g. the same logging system).

In [14]:
columns_with_missing = df.columns[df.isna().any()].tolist()

if len(columns_with_missing) < 2:
    print("At least two columns with missing values are needed for clustering.")
else:
    # Each row represents one dataset variable; each column represents an
    # observation. Variables with similar missingness patterns cluster together.
    missing_matrix = df[columns_with_missing].isna().astype(int).T

    fig = ff.create_dendrogram(
        missing_matrix.values,
        labels=columns_with_missing,
        linkagefun=lambda x: hierarchy.linkage(x, method="ward"),
    )
    fig.update_layout(
        title="Clustering of Variables by Missing-Value Pattern",
        xaxis_title="Variable",
        yaxis_title="Distance",
        height=500,
    )
    show_plotly(fig)

At least two columns with missing values are needed for clustering.


## 3. Step 2 — Check data quality

EDA identifies potential issues **before** changing the data. Duplicates, suspicious identifiers, and implausible values are **detected and reported only** — nothing is deleted.

### 3.1 Duplicate rows and duplicated keys

The dataset has no single row identifier. Logically, one row should be unique for the combination **`Date` + `Store ID` + `Product ID`**, so we check both fully duplicated rows and repeated keys. A repeated key whose other values differ is a different (and more serious) problem than an exact copy of a row.

In [15]:
number_of_duplicates = df.duplicated().sum()
percentage_duplicates = 100 * number_of_duplicates / len(df) if len(df) else 0

print(f"Duplicate rows: {number_of_duplicates:,}")
print(f"Percentage of dataset: {percentage_duplicates:.2f}%")

# The same duplicated() check, applied only to the logical key columns.
KEY_COLUMNS = ["Date", "Store ID", "Product ID"]
number_of_duplicate_keys = df.duplicated(subset=KEY_COLUMNS).sum()
print(f"\nRepeated {' + '.join(KEY_COLUMNS)} combinations: {number_of_duplicate_keys:,}")
print(f"Repeated keys that are NOT exact duplicate rows: {number_of_duplicate_keys - number_of_duplicates:,}")

Duplicate rows: 0
Percentage of dataset: 0.00%

Repeated Date + Store ID + Product ID combinations: 0
Repeated keys that are NOT exact duplicate rows: 0


### 3.2 Unique values per column

Helpful for detecting ID-like variables, binary flags, and unexpected categories. Compare `unique_values` with the feature dictionary: `Store ID` should have 5 levels, `Product ID` 20, `Category` 5, `Region` 4, `Weather Condition` 4, and `Seasonality` 4.

In [16]:
unique_summary = pd.DataFrame({
    "dtype": df.dtypes.astype(str),
    "unique_values": df.nunique(dropna=False),
})
unique_summary["unique_percent"] = unique_summary["unique_values"] / len(df) * 100

display(unique_summary.sort_values("unique_values"))

,dtype,unique_values,unique_percent
Holiday/Promotion,int64,2,0.003
Region,object,4,0.005
Weather Condition,object,4,0.005
Seasonality,object,4,0.005
Discount,int64,5,0.007
Store ID,object,5,0.007
Category,object,5,0.007
Product ID,object,20,0.027
Units Ordered,int64,181,0.248
Inventory Level,int64,451,0.617


### 3.3 Plausibility checks (business rules)

The descriptive statistics in Section 2.4 suggest checking a few simple retail rules. Each line only **counts** the rows that violate a rule; nothing is changed.

- A demand forecast should not be negative.
- A store cannot sell more units than it has in stock.
- Days with zero sales are possible, but worth knowing about.

In [17]:
print(f"Rows with negative Demand Forecast        : {(df['Demand Forecast'] < 0).sum():,}")
print(f"Rows with Units Sold > Inventory Level     : {(df['Units Sold'] > df['Inventory Level']).sum():,}")
print(f"Rows with Units Sold = 0                   : {(df['Units Sold'] == 0).sum():,}")

Rows with negative Demand Forecast        : 673
Rows with Units Sold > Inventory Level     : 0
Rows with Units Sold = 0                   : 360


Remark : delate rows with negative Demand Forecast

> **Checkpoint:** Which variables are identifiers? Do the categorical variables contain levels that are not listed in the feature dictionary? Are any numerical ranges impossible from a retail perspective? (The frequency tables in Section 4.1 show the category levels in detail; Section 7 checks whether each product always belongs to the same category and each store to the same region.)

Identifiers : Store ID and Product ID. 

We do not have the feature dictionary. 

The ranges analysis for the numerical columns is provided as a table for the ranges that are problematic and as bullet points below. 

#### Ranges that make sense

- **`Inventory Level` (50–500):** there is no negative stock and no zero stock. That is plausible for one product in one store.
- **`Units Sold` (0–499):** there are no negative values, and sales never exceed the stock on hand. 360 days have zero sales, which is normal. The distribution is right-skewed (median 107, mean 136), as sales data usually is.
- **`Units Ordered` (20–200):** a plausible range for replenishment order quantities.
- **`Discount` (0, 5, 10, 15, 20 %):** these are typical retail discount levels.
- **`Holiday/Promotion` (0/1):** the binary flag is correctly coded.

#### Ranges that are problematic

| Column | Finding | Why it is implausible in retail |
|---|---|---|
| `Demand Forecast` | The minimum is −9.99, and 673 rows (≈0.9 %) are negative. | Demand cannot be negative, so a forecast should never go below 0. |
| `Price` (by category) | Every category has a range of 10–100 and a median of ≈55. | Furniture and electronics normally cost far more than groceries, but here the price ranges are identical. |
| `Price` (by product) | The price of P0001 in store S001 varies between 10.26 and 99.97 from day to day. | A product's price is normally stable and changes mainly through discounts. Here it varies up to tenfold at random. |
| `Competitor Pricing` | The difference from our price is always between −5 and +5 in absolute terms, and the minimum is 5.03. | On an item priced at 10, a difference of 5 is ≈50 %; on an item priced at 100, it is only 5 %. A fixed absolute gap instead of a percentage gap is unrealistic. |
| `Units Sold` ÷ `Inventory Level` | The ratio is spread evenly from 0 % to 100 %. ≈10 % of rows sell at least 90 % of their stock in a single day. | Daily sell-through that high is very rare. Retailers normally keep stock to cover several days. |
| `Units Sold` (scale) | The median is 107 units per product per day, or ≈2,700 units per store per day. | For furniture and electronics, selling 100+ units of one product per day in one store is very high. |
| `Inventory Level` over time | The rule *stock tomorrow = stock today − units sold + units ordered* holds in only 0.2 % of rows. The correlation between today's and yesterday's stock is ≈0. | In a real store, stock carries over from one day to the next. Here it is effectively a new random number each day. |
| `Units Ordered` over time | The value is above 0 every single day for every product. | Real replenishment usually arrives periodically, e.g. weekly, not every day. |

> **Note:** The currency is not stated, so the 10–100 price scale can only be judged in relative terms (between categories and over time), not in absolute terms.

**Conclusion:** each column's range looks clean on its own, but the relationships between columns do not follow retail logic. Together with the uniform distributions (kurtosis ≈ −1.2), this suggests the dataset is **synthetic**. The only issue that requires treatment later is the negative `Demand Forecast` values. The other findings are documented as data limitations, and nothing is changed in `df`.

## 4. Step 3 — Understand each variable (univariate analysis)

Univariate analysis studies **one variable at a time**. Categorical and numerical variables are treated differently.

### 4.1 Categorical variables

Frequency tables for `Store ID`, `Product ID`, `Category`, `Region`, `Weather Condition`, and `Seasonality`. For high-cardinality variables (`Product ID`), only the 15 most frequent levels are shown.

In [18]:
if not categorical_columns:
    print("No categorical variables detected.")
else:
    for col in categorical_plot_columns:
        print(f"\n--- {col} ---")
        counts = df[col].value_counts(dropna=False).head(15)
        display(counts.to_frame(name="count"))


--- Store ID ---


,count
Store ID,
S001,14620
S002,14620
S003,14620
S004,14620
S005,14620



--- Product ID ---


,count
Product ID,
P0001,3655
P0002,3655
P0003,3655
P0004,3655
P0005,3655
P0006,3655
P0007,3655
P0008,3655
P0009,3655



--- Category ---


...

,count
Region,
East,18349
South,18297
North,18228
West,18226



--- Weather Condition ---


,count
Weather Condition,
Sunny,18290
Rainy,18278
Snowy,18272
Cloudy,18260



--- Seasonality ---


,count
Seasonality,
Spring,18317
Summer,18305
Winter,18285
Autumn,18193


#### Interactive frequency bar charts

A frequency bar chart answers: **How many observations belong to each category?** Look for rare, unexpected levels.

In [19]:
# Plot an interactive frequency bar chart for each selected categorical variable.
if not categorical_plot_columns:
    print("No categorical variables detected.")
else:
    for col in categorical_plot_columns:
        # Convert values to pandas' string type so both category dtype and
        # missing values are handled consistently.
        plot_series = df[col].astype("string").fillna("<Missing>")

        # Count categories and keep the 15 most frequent for readability.
        counts = plot_series.value_counts().head(15)
        counts_df = counts.rename("Frequency").reset_index()
        counts_df.columns = ["Category", "Frequency"]

        fig = px.bar(
            counts_df,
            x="Category",
            y="Frequency",
            title=f"Frequency of {col}",
            text="Frequency",
            labels={"Category": col, "Frequency": "Number of rows"},
        )
        fig.update_layout(xaxis_tickangle=-45)
        show_plotly(fig)

**Remarks — frequency bar charts**

- **`Store ID`:** each of the 5 stores has exactly **14,620 rows** (20 %). That equals 731 days × 20 products, so every store reports every product on every day. The panel is complete and perfectly balanced.
- **`Product ID`:** each product has exactly **3,655 rows** (5 %), i.e. 731 days × 5 stores. The chart shows only the 15 most frequent products, so P0016–P0020 are hidden, but they have the same count.
- **`Category`:** almost perfectly balanced, from Furniture (14,699) down to Electronics (14,521), each ≈ 20 %. Unlike `Store ID` and `Product ID`, the counts are *not* exactly equal. That is because a product's category is not fixed (checked in Section 7).
- **`Region`:** almost perfectly balanced, from East (18,349) down to West (18,226), each ≈ 25 %. Again the counts are not exact multiples of the store count, because a store's region is not fixed.
- **`Weather Condition`:** Sunny, Rainy, Snowy and Cloudy each make up ≈ 25 % (18,260–18,290 rows). In real data, snowy days would be much rarer than sunny or cloudy days, so this label looks randomly generated.
- **`Seasonality`:** Spring (18,317), Summer (18,305), Winter (18,285) and Autumn (18,193) each make up ≈ 25 %. Since the data covers two full years, equal season shares are expected. However, the label is **not linked to the calendar month**: in June–August only ≈ 25 % of rows are labelled "Summer", the same share as every other season. For calendar effects, a season derived from `Date` is therefore more reliable than this column.

**Overall:** none of the categorical variables has rare or unexpected levels, so no class-imbalance treatment is needed. The near-perfectly uniform frequencies are unusual for real retail data and support the conclusion that the dataset is **synthetic**. Because every level is equally represented, any later differences in `Units Sold` between groups cannot be explained by sample size.

#### Interactive pie charts — only when the number of categories is small

Pie charts are created only for variables with at most 10 categories (`Product ID` is skipped automatically).

In [20]:
for col in categorical_plot_columns:
    plot_series = df[col].astype("string").fillna("<Missing>")
    number_of_categories = plot_series.nunique(dropna=False)

    if number_of_categories <= 10:
        counts = plot_series.value_counts()
        pie_df = counts.rename("Frequency").reset_index()
        pie_df.columns = ["Category", "Frequency"]

        fig = px.pie(
            pie_df,
            names="Category",
            values="Frequency",
            title=f"Share of {col}",
            hole=0.25,
        )
        fig.update_traces(textposition="inside", textinfo="percent+label")
        show_plotly(fig)
    else:
        print(
            f"Skipping pie chart for {col}: "
            f"{number_of_categories} categories would be difficult to read."
        )

Skipping pie chart for Product ID: 20 categories would be difficult to read.


#### Interactive Pareto charts

A Pareto chart ranks categories by frequency and overlays the cumulative percentage. We draw it for `Category` and for `Product ID` (how evenly are the observations spread over the 20 products?).

In [21]:
for pareto_col in ["Store ID", "Product ID", "Category", "Region", "Weather Condition", "Seasonality"]:

    if pareto_col is None:
        print("No categorical variable is available for a Pareto chart.")
        continue

    pareto_series = df[pareto_col].astype("string").fillna("<Missing>")

    # Count categories from most to least frequent.
    freq = pareto_series.value_counts().sort_values(ascending=False)
    cumulative_percent = freq.cumsum() / freq.sum() * 100

    pareto_df = pd.DataFrame({
        "Category": freq.index.astype(str),
        "Frequency": freq.values,
        "Cumulative percentage": cumulative_percent.values,
    })

    # Two y-axes are needed because frequencies and percentages use
    # different scales.
    fig = make_subplots(specs=[[{"secondary_y": True}]])

    fig.add_trace(
        go.Bar(
            x=pareto_df["Category"],
            y=pareto_df["Frequency"],
            name="Frequency",
            text=pareto_df["Frequency"],
        ),
        secondary_y=False,
    )

    fig.add_trace(
        go.Scatter(
            x=pareto_df["Category"],
            y=pareto_df["Cumulative percentage"],
            name="Cumulative %",
            mode="lines+markers",
        ),
        secondary_y=True,
    )

    fig.update_layout(
        title=f"Pareto Chart of {pareto_col}",
        xaxis_title=pareto_col,
        xaxis_tickangle=-45,
    )
    fig.update_yaxes(title_text="Frequency", secondary_y=False)
    fig.update_yaxes(title_text="Cumulative percentage (%)", range=[0, 105], secondary_y=True)
    show_plotly(fig)

Remarks: We can notice that the slope of all pareto charts is approximately/exactly equals to 1, which back our claim from the previous remarks deducted from the bar charts. This is unusual in the real world retail data scenarios because usually the frequency for each distinct category from a certain column is not the same. And in this case, the slope of the line in its respective pareto chart will have different values when moving from one distinct category to the other.

### 4.2 Numerical variables

Box plots, violin plots, histograms, density plots, skewness/kurtosis, and z-scores are used to understand all 8 numerical variables (7 features + the target).

#### Interactive box plots

Box plots summarize the median, spread, and potential outliers.

In [22]:
if not numeric_plot_columns:
    print("No numerical variables detected.")
else:
    for col in numeric_plot_columns:
        fig = px.box(
            df,
            y=col,
            points="outliers",
            title=f"Box Plot of {col}",
        )
        fig.update_layout(height=450)
        show_plotly(fig)

**Remarks — box plots of the numerical variables**

| Variable | Median | IQR (Q1–Q3) | Range |
|---|---|---|---|
| `Inventory Level` | 273 | 162–387 | 50–500 |
| `Units Sold` (target) | 107 | 49–203 | 0–499 |
| `Units Ordered` | 110 | 65–155 | 20–200 |
| `Demand Forecast` | 113.0 | 53.7–208.1 | −9.99–518.55 |
| `Price` | 55.05 | 32.65–77.86 | 10–100 |
| `Discount` | 10 | 5–15 | 0–20 |
| `Holiday/Promotion` | 0 | 0–1 | 0–1 |
| `Competitor Pricing` | 55.01 | 32.68–77.82 | 5.03–104.94 |

- **`Units Sold` and `Demand Forecast`** are the only variables with outliers, and only on the **upper side**. The median sits closer to Q1 than to Q3, which confirms the right skew. The outliers (≈1 % each) are high-sales days that are still within the plausible range (≤ 499 units, never above `Inventory Level`). They look like genuine demand peaks rather than errors, so they are **kept**. The two boxes look almost identical, which is the first sign of the near-perfect correlation between the forecast and the target (Section 5.5).
- **`Demand Forecast`** also has its lower whisker below 0 (min −9.99). The box plot flags no lower outliers, but negative values are impossible from a business point of view (see Section 3.3).
- **`Inventory Level`, `Units Ordered`, `Price`, `Competitor Pricing`:** the median lies in the middle of the box, and the whiskers reach exactly the minimum and maximum, with no outliers. This symmetric, hard-bounded shape is typical of a **uniform distribution**. It is unusual for real retail data, where prices and stock levels tend to cluster around typical values.
- **`Discount` and `Holiday/Promotion`** are discrete variables (5 levels and 0/1). A box plot is not very informative for them; the frequency tables and the box plots of the target by group (Section 5.3) are more useful.

**Overall:** no variable has extreme or implausible outliers, so no outlier treatment is needed. The only issue to treat later is the negative `Demand Forecast` values.

**Remarks — box plots of the numerical variables**

- **Sales and forecast are the only skewed variables.** In the `Units Sold` and `Demand Forecast` boxes, the median sits closer to the bottom of the box. Points appear only above the upper whisker. Most store–product–days therefore sell moderate quantities, and a small group of days sells much more. These high-sales days are still realistic (they never exceed the available inventory), so they are best read as genuine demand peaks rather than errors, and they are kept.
- **The forecast mirrors the target.** The `Demand Forecast` box looks almost identical to the `Units Sold` box. This is a first visual hint that the forecast follows actual sales very closely, which we examine later as possible target leakage (Section 5.5).
- **One implausible detail:** the lower whisker of `Demand Forecast` extends slightly below zero. Negative demand is impossible in retail, so these values need attention during data preparation.
- **Inventory, orders, and prices look artificially even.** For `Inventory Level`, `Units Ordered`, `Price`, and `Competitor Pricing`, the median sits in the middle of the box and the whiskers stop exactly at the minimum and maximum, with no outliers. This flat, symmetric shape suggests values spread evenly across a fixed range. Real retail data usually clusters around typical stock levels and price points, so this supports the view that the dataset is synthetic.
- **Discrete variables are not well suited to box plots.** `Discount` (five levels) and `Holiday/Promotion` (yes/no) produce simple, uninformative boxes. Their frequency tables and their effect on sales (Section 5.3) tell us more.

**Overall:** the numerical variables are clean, with no extreme or suspicious outliers that would require treatment. The most interesting patterns are the right-skewed sales, the close resemblance between forecast and sales, and the unnaturally uniform spread of the inventory and price variables.

#### Interactive grouped box plots

Each numerical variable is compared across `Category` (x-axis) and `Region` (colour). Different product categories might be expected to have different price levels, stock levels, or sales volumes.

In [23]:
if group_col is None:
    print("No grouping variable is available for grouped box plots.")
else:
    for col in numeric_plot_columns:
        # Work on a temporary copy so categorical display formatting does not
        # change the original dataset.
        plot_df = df.copy()
        plot_df[group_col] = plot_df[group_col].astype("string").fillna("<Missing>")

        color_col = None
        if hue_col is not None and hue_col != group_col:
            plot_df[hue_col] = plot_df[hue_col].astype("string").fillna("<Missing>")
            color_col = hue_col

        fig = px.box(
            plot_df,
            x=group_col,
            y=col,
            color=color_col,
            points="outliers",
            title=f"{col} by {group_col}",
        )
        fig.update_layout(xaxis_tickangle=-30)
        show_plotly(fig)

**Remarks — grouped box plots (by `Category` and `Region`)**

- **The groups are practically indistinguishable.** For every numerical variable, the 20 boxes (5 categories × 4 regions) have almost the same median, box height, and whisker length. No category or region stands out as selling more, holding more stock, ordering more, or charging higher prices.
- **Sales do not depend on category or region.** The `Units Sold` boxes look the same for Groceries, Electronics, Furniture, Clothing, and Toys, in every region. The small shifts between boxes are within normal random variation. Category and region are therefore unlikely to be useful predictors on their own. The same holds for `Demand Forecast`, whose boxes again mirror those of `Units Sold`.
- **Prices are identical across categories.** The `Price` and `Competitor Pricing` boxes cover the same range with the same median for every category. In real retail, furniture and electronics would sit far above groceries and clothing. This confirms the earlier finding that price is not linked to the type of product.
- **Inventory and orders show no category-specific policy.** Real retailers usually keep more stock of fast-moving goods (e.g. groceries) and less of bulky or expensive items (e.g. furniture). Here, `Inventory Level` and `Units Ordered` look the same in every group, so there is no visible replenishment strategy by category or region.
- **Outliers appear only for sales and forecast.** Every category–region group contains a few high-sales days. Demand peaks are therefore spread evenly rather than concentrated in a particular product type or location.
- **Discrete variables:** `Discount` produces identical boxes everywhere (median 10 %). `Holiday/Promotion` is roughly half 0 and half 1 in every group. Because of that 50/50 split, its median switches between 0 and 1 from group to group. This is a statistical artifact, not a real difference.

**Overall:** neither `Category` nor `Region` separates the data in any meaningful way. This matches the Cramér's V results (Section 7) and is another strong sign of a synthetic dataset. For modelling, these two variables are expected to add little explanatory power.

#### Interactive violin plots

A violin plot adds **distribution shape** to the box-plot summary. Look for multi-modal shapes (several peaks) or flat, uniform-looking shapes.

In [24]:
for col in numeric_plot_columns:
    plot_df = df.copy()

    if group_col is not None:
        plot_df[group_col] = plot_df[group_col].astype("string").fillna("<Missing>")

    fig = px.violin(
        plot_df,
        x=group_col if group_col is not None else None,
        y=col,
        color=group_col if group_col is not None else None,
        box=True,
        points="outliers",
        title=f"Violin Plot of {col}",
    )
    fig.update_layout(xaxis_tickangle=-30)
    show_plotly(fig)

**Remarks — violin plots (by `Category`)**

- **Sales and forecast have a "teardrop" shape.** The `Units Sold` and `Demand Forecast` violins are widest near the bottom and taper into a long, thin tail at the top. On most store–product–days, low to moderate quantities are sold: about half of all rows sell fewer than 100 units. High-sales days become steadily rarer. This is the typical shape of real demand data, and it confirms the right skew seen in the box plots.
- **The violins are smoothed.** The bottom of the `Units Sold` violin may extend slightly below zero. This comes from the smoothing used to draw the curve, not from the data: actual sales never go below 0.
- **Inventory, orders, and prices look like rectangles.** The violins for `Inventory Level`, `Units Ordered`, `Price`, and `Competitor Pricing` have almost the same width from bottom to top. Every value in the range is equally likely, with no typical stock level or typical price point. Real retail data would normally show a bulge around common values, so this flat shape is another strong sign of a **uniform, synthetic distribution**.
- **Discrete variables show separate bulges.** `Discount` appears as five equally sized bulges (0, 5, 10, 15, 20 %). `Holiday/Promotion` appears as two equal bulges at 0 and 1. The violin is not a meaningful summary for these variables. It only shows that each level occurs about equally often.
- **All five categories look identical.** For every variable, the violins of Clothing, Electronics, Furniture, Groceries, and Toys are practically copies of each other. There are no extra peaks, distinct operating regimes, or category-specific patterns. A real product mix would show different shapes, for example many small grocery sales versus few furniture sales.

**Overall:** the violin plots confirm what the box plots suggested. Sales and forecast follow a realistic right-skewed shape. All other numerical variables are flat and uniform, and product category does not change the shape of any distribution.

#### Interactive histograms, skewness, and kurtosis

- A **histogram** shows how observations are distributed across value ranges. Watch for **pile-ups at the edges** (e.g. many values exactly at a minimum or maximum), which suggest values were capped/clipped, and for **flat (uniform) shapes**, which are unusual for real sales data.
- **Skewness** describes asymmetry (|skew| > 1 is usually considered strongly skewed).
- **Kurtosis** describes tail heaviness relative to a normal distribution (large values = heavy tails; values near −1.2 are typical for a uniform distribution).

In [25]:
for col in numeric_plot_columns:
    plot_df = df.copy()

    # Treat low-cardinality hue variables as categories rather than continuous
    # color scales.
    color_col = hue_col
    if color_col is not None:
        plot_df[color_col] = plot_df[color_col].astype("string").fillna("<Missing>")

    fig = px.histogram(
        plot_df,
        x=col,
        color=color_col,
        nbins=30,
        marginal="box",
        opacity=0.75,
        barmode="overlay" if color_col is not None else "relative",
        title=f"Distribution of {col}",
    )
    show_plotly(fig)

    print(f"{col}")
    print(f"  Skewness: {df[col].skew():.3f}")
    print(f"  Kurtosis: {df[col].kurt():.3f}")

Inventory Level
  Skewness: 0.010
  Kurtosis: -1.200


Units Sold
  Skewness: 0.905
  Kurtosis: 0.054


Units Ordered
  Skewness: 0.004
  Kurtosis: -1.202


Demand Forecast
  Skewness: 0.895
  Kurtosis: 0.049


Price
  Skewness: -0.003
  Kurtosis: -1.199


Discount
  Skewness: -0.002
  Kurtosis: -1.305


Holiday/Promotion
  Skewness: 0.011
  Kurtosis: -2.000


Competitor Pricing
  Skewness: -0.002
  Kurtosis: -1.170


**Remarks — histograms, skewness, and kurtosis (coloured by `Region`)**

| Variable | Skewness | Kurtosis | Shape |
|---|---|---|---|
| `Inventory Level` | 0.010 | −1.200 | flat / uniform |
| `Units Sold` (target) | 0.905 | 0.054 | moderately right-skewed |
| `Units Ordered` | 0.004 | −1.202 | flat / uniform |
| `Demand Forecast` | 0.895 | 0.049 | moderately right-skewed |
| `Price` | −0.003 | −1.199 | flat / uniform |
| `Discount` | −0.002 | −1.305 | five equal spikes (discrete) |
| `Holiday/Promotion` | 0.011 | −2.000 | two equal spikes (binary) |
| `Competitor Pricing` | −0.002 | −1.170 | flat / uniform |

- **Sales and forecast are the only variables with a "natural" shape.** The `Units Sold` and `Demand Forecast` histograms are tallest at low values and decline steadily towards higher quantities. That is a moderate right skew (≈ 0.9), as is typical for retail demand. Their kurtosis is close to 0, so the tails are not unusually heavy, and the high-sales days are rare but not extreme. For modelling, the skew is mild enough that a transformation is optional rather than necessary.
- **The forecast again mirrors the target.** The two histograms have almost the same shape, skewness, and kurtosis. This adds to the evidence that `Demand Forecast` is very closely tied to `Units Sold`.
- **All other continuous variables are flat.** `Inventory Level`, `Units Ordered`, `Price`, and `Competitor Pricing` show bars of roughly equal height across their whole range. Their skewness is ≈ 0 and their kurtosis is ≈ −1.2, which is the textbook value for a **uniform distribution**. There are no pile-ups at the minimum or maximum, so the values do not appear to have been capped. They seem to have been generated evenly within a fixed range.
- **Discrete variables:** `Discount` appears as five spikes of equal height, and `Holiday/Promotion` as two equal spikes. Their very negative kurtosis (−1.3 and −2.0) simply reflects this, and is not a data problem.
- **The regions overlap completely.** For every variable, the coloured histograms of East, North, South, and West lie on top of each other with the same shape. Region does not shift or reshape any distribution.

**Overall:** apart from the realistic right-skewed sales and forecast, the numerical variables are uniformly distributed and identical across regions. That is unusual for real retail data and consistent with a synthetic dataset. No variable needs outlier or skewness treatment before modelling. The only item to fix is the negative values in `Demand Forecast`.

#### Interactive density plots for selected numerical variables

Density curves are only comparable when variables share a unit. We therefore overlay variables in two groups with a common scale: **quantities (units)** and **prices**.

In [26]:
density_groups = {
    "Quantity variables (units)": ["Units Sold", "Demand Forecast", "Inventory Level", "Units Ordered"],
    "Price variables": ["Price", "Competitor Pricing"],
}

for group_title, density_columns in density_groups.items():

    if not density_columns:
        print("No numerical variables available for a density plot.")
        continue

    fig = go.Figure()

    for col in density_columns:
        clean_values = df[col].dropna().astype(float)

        # KDE requires at least two observations and non-zero variation.
        if len(clean_values) >= 2 and clean_values.nunique() > 1:
            kde = gaussian_kde(clean_values)
            x_grid = np.linspace(clean_values.min(), clean_values.max(), 250)
            density = kde(x_grid)

            fig.add_trace(
                go.Scatter(
                    x=x_grid,
                    y=density,
                    mode="lines",
                    name=col,
                    hovertemplate="Value=%{x:.3f}<br>Density=%{y:.4f}<extra>%{fullData.name}</extra>",
                )
            )

    if len(fig.data) == 0:
        print("Selected numerical variables do not have enough variation for KDE.")
    else:
        fig.update_layout(
            title=f"Density Plot — {group_title}",
            xaxis_title="Value",
            yaxis_title="Density",
            hovermode="x unified",
        )
        show_plotly(fig)

#### Interactive z-score distribution for potential outlier detection

A z-score measures how many standard deviations an observation lies from the mean. Values beyond approximately **±3** are inspected as potential outliers, but they are **not removed**. In retail data, very high sales days can be genuine demand peaks (which the replenishment team explicitly wants to understand), while others may be recording errors.

The table first counts the observations with |z| > 3 per variable; the histograms follow.

In [27]:
outlier_counts = {}

for col in numeric_plot_columns:
    clean_values = df[col].dropna().astype(float)

    if len(clean_values) < 2 or clean_values.nunique() <= 1:
        print(f"Skipping {col}: insufficient variation for z-scores.")
        continue

    # Calculate z-scores without adding a temporary column to the original df.
    z_values = zscore(clean_values, nan_policy="omit")
    outlier_counts[col] = int((np.abs(z_values) > 3).sum())

outlier_summary = pd.DataFrame({"observations_with_abs_z_above_3": pd.Series(outlier_counts)})
outlier_summary["percent_of_non_missing"] = outlier_summary["observations_with_abs_z_above_3"] / df[outlier_summary.index].notna().sum() * 100
display(outlier_summary.sort_values("observations_with_abs_z_above_3", ascending=False))

,observations_with_abs_z_above_3,percent_of_non_missing
Demand Forecast,241,0.330
Units Sold,236,0.323
Inventory Level,0,0.000
Units Ordered,0,0.000
Price,0,0.000
Discount,0,0.000
Holiday/Promotion,0,0.000
Competitor Pricing,0,0.000


**Remarks — z-score outlier summary (|z| > 3)**

| Variable | Observations with \|z\| > 3 | % of rows |
|---|---|---|
| `Demand Forecast` | 241 | 0.33 % |
| `Units Sold` (target) | 236 | 0.32 % |
| all other variables | 0 | 0.00 % |

- **Only sales and forecast contain potential outliers, and only on the high side.** A z-score above 3 corresponds to roughly **more than 463 units sold** (mean 136 + 3 × SD 109), and similarly about 469 for the forecast. On the low side, mean − 3 × SD is far below zero, so low outliers are impossible. All flagged rows are therefore exceptionally strong sales days.
- **The share of outliers is small and expected.** About 0.3 % of rows exceed |z| > 3. That is close to what a normal distribution would produce (≈ 0.27 %), so the tails are not unusually heavy. These rows are plausible demand peaks (they never exceed the available inventory), not recording errors, and they are **kept**.
- **Sales and forecast flag almost the same number of rows.** This is another sign that the forecast moves almost one-to-one with actual sales.
- **Uniform variables cannot produce z-score outliers.** For a uniformly distributed variable, the most extreme value lies only about 1.7 standard deviations from the mean. `Inventory Level`, `Units Ordered`, `Price`, and `Competitor Pricing` can therefore never reach |z| > 3. The zero count reflects their flat shape rather than proof of "perfectly clean" data. The same applies to the discrete `Discount` and `Holiday/Promotion`.
- **This differs from the box plot.** The box plot's 1.5 × IQR rule flags about 715 high-sales rows, compared with 236 here. The z-score rule is stricter, so it marks only the most extreme peaks.

**Overall:** the dataset has no problematic outliers. The few extreme values are realistic high-demand days that a forecasting model should learn from rather than discard. If anything, they may slightly influence a squared-error model, which is worth keeping in mind during modelling.

In [28]:
for col in numeric_plot_columns:
    clean_values = df[col].dropna().astype(float)

    if len(clean_values) < 2 or clean_values.nunique() <= 1:
        print(f"Skipping {col}: insufficient variation for z-scores.")
        continue

    # Calculate z-scores without adding a temporary column to the original df.
    z_values = zscore(clean_values, nan_policy="omit")
    z_df = pd.DataFrame({"Z-score": z_values})

    fig = px.histogram(
        z_df,
        x="Z-score",
        nbins=30,
        marginal="box",
        title=f"Z-Score Distribution — {col}",
    )
    fig.add_vline(x=-3, line_dash="dash", annotation_text="-3")
    fig.add_vline(x=3, line_dash="dash", annotation_text="+3")
    show_plotly(fig)

> **Checkpoint:** For one numerical variable, describe its typical value, spread, skewness, and possible outliers. Then explain why these patterns might matter for a units-sold prediction.

**Checkpoint answer — `Units Sold` (the target)**

- **Typical value:** the median is 107 units per store–product–day, and the mean is higher at ≈136 units because a minority of high-sales days pulls it up.
- **Spread:** wide. The middle 50 % of days lie between 49 and 203 units, and the full range is 0–499. Sales never exceed `Inventory Level`.
- **Skewness:** moderately right-skewed (≈ 0.9), with excess kurtosis ≈ 0. Most days have moderate sales; very high sales are rare.
- **Outliers:** only on the high side, ≈0.3 % of rows above ≈463 units (|z| > 3). These are plausible demand peaks, so they are kept.

**Why it matters:** a squared-error model (RMSE) gives these peaks a lot of weight and may over-forecast typical days, so MAE should be reported as well. Predictions should stay between 0 and `Inventory Level`. The peak days should not be removed, because they are exactly where stock-outs are most likely.

## 5. Step 4 — Target-focused analysis (`Units Sold`)

Because the downstream task is **regression**, we look explicitly at the target and its relationship with every feature.

### 5.1 Distribution of the target

A right-skewed target with a long tail of very high values matters for modelling: a few high-sales days can dominate a squared-error loss.

In [29]:
fig = px.histogram(
    df,
    x=target_col,
    nbins=60,
    marginal="box",
    opacity=0.75,
    title=f"Distribution of the target: {target_col}",
)
show_plotly(fig)

print(f"{target_col}")
print(f"  Non-missing values: {df[target_col].notna().sum():,} of {len(df):,}")
print(f"  Skewness: {df[target_col].skew():.3f}")
print(f"  Kurtosis: {df[target_col].kurt():.3f}")

Units Sold
  Non-missing values: 73,100 of 73,100
  Skewness: 0.905
  Kurtosis: 0.054


### 5.2 Target by category and region

Do some product categories or regions sell systematically more units?

In [30]:
plot_df = df.copy()
plot_df[group_col] = plot_df[group_col].astype("string").fillna("<Missing>")
plot_df[hue_col] = plot_df[hue_col].astype("string").fillna("<Missing>")

fig = px.box(
    plot_df,
    x=group_col,
    y=target_col,
    color=hue_col,
    points="outliers",
    title=f"{target_col} by {group_col} and {hue_col}",
)
fig.update_layout(xaxis_tickangle=-30)
show_plotly(fig)

fig = px.violin(
    plot_df,
    x=hue_col,
    y=target_col,
    color=hue_col,
    box=True,
    points="outliers",
    title=f"Violin Plot of {target_col} by {hue_col}",
)
show_plotly(fig)

### 5.3 Target by the other categorical and discrete variables

The same box-plot code is applied to `Weather Condition`, `Seasonality`, `Store ID`, and to the two discrete numerical variables `Holiday/Promotion` and `Discount` (cast to strings for the chart only, so Plotly treats them as categories). Do weather, season, store, promotions, or discounts shift the sales distribution?

In [31]:
target_box_columns = ["Weather Condition", "Seasonality", "Store ID", "Holiday/Promotion", "Discount"]

for box_col in target_box_columns:
    # Work on a temporary copy so categorical display formatting does not
    # change the original dataset.
    plot_df = df.copy()
    plot_df[box_col] = plot_df[box_col].astype("string").fillna("<Missing>")

    fig = px.box(
        plot_df,
        x=box_col,
        y=target_col,
        color=box_col,
        points="outliers",
        title=f"{target_col} by {box_col}",
    )
    fig.update_layout(xaxis_tickangle=-30)
    show_plotly(fig)

### 5.4 Each numerical feature vs. the target

One scatter plot per feature, coloured by category (random sample of `SCATTER_MAX_ROWS` rows, for the chart only). Look for:

- **near-perfect lines** — a feature that almost equals the target (possible target leakage),
- **upper or lower bounds** — e.g. sales that can never exceed the available inventory (a triangular cloud),
- **flat clouds** — no visible relationship,
- **group-specific slopes** — different patterns per category (possible interactions).

`Discount` and `Holiday/Promotion` appear as vertical stripes because they take only a few values; Section 5.3 shows them more clearly.

In [32]:
for feature in feature_columns:
    # Plotting copy only: a random sample keeps the interactive chart responsive.
    plot_df = df.sample(
        min(SCATTER_MAX_ROWS, len(df)),
        random_state=42,
    ).copy()

    # Cast the category to strings so Plotly treats it as categories.
    plot_df[group_col] = plot_df[group_col].astype("string").fillna("<Missing>")

    fig = px.scatter(
        plot_df,
        x=feature,
        y=target_col,
        color=group_col,
        opacity=0.5,
        title=f"{target_col} vs. {feature}",
        hover_data=[c for c in ["Store ID", "Product ID", hue_col] if c is not None and c in plot_df.columns],
    )
    show_plotly(fig)

**Remarks — each numerical feature vs. `Units Sold`**

- **`Demand Forecast` → an almost perfect diagonal line.** The points form a narrow band along the 45° line: the forecast lies within about −10 to +20 units of actual sales and over-forecasts by ≈5 units on average. A real forecast made *before* the sales day would rarely be this accurate, so this is a strong warning sign of **target leakage**. The feature should not be used for prediction unless it is clearly available in advance.
- **`Inventory Level` → a triangle.** Every point lies below the diagonal, so sales never exceed available stock. Below that ceiling, the points are spread evenly. Inventory therefore acts as an **upper bound** on sales rather than a linear driver: high stock *allows* high sales but does not guarantee them. A linear model would capture this only partially.
- **`Units Ordered`, `Price`, `Competitor Pricing` → flat, shapeless clouds.** Sales look the same at every order quantity and price level. There is no visible demand curve (higher prices do not reduce sales), which contradicts basic retail economics.
- **`Discount` and `Holiday/Promotion` → vertical stripes.** Because these variables take only a few values, the points stack into columns. All stripes cover the same range of sales, so neither discounts nor promotions visibly lift demand.
- **Category colours are fully mixed.** In every plot, the five categories overlap completely. There are no category-specific slopes or interactions.

**Overall:** apart from the leakage-prone forecast, inventory is the only feature with a visible relationship to sales, and that relationship is a ceiling rather than a straight line. Pricing, ordering, and promotion variables show no effect, which is another indication of a synthetic dataset.

### 5.5 Correlation of each feature with the target — Pearson vs. Spearman

- **Pearson** measures *linear* association and is sensitive to outliers.
- **Spearman** measures *monotonic* association using ranks and is robust to outliers.

When Spearman is clearly larger than Pearson, the relationship is likely **nonlinear** and/or distorted by **extreme values**. A near-zero coefficient does **not** prove there is no relationship: a U-shaped pattern can have a correlation close to zero. Both coefficients use all 73,100 rows.

In [33]:
pearson_matrix = df[numeric_columns].corr(method="pearson")
spearman_matrix = df[numeric_columns].corr(method="spearman")

target_corr = pd.DataFrame({
    "Pearson": pearson_matrix[target_col],
    "Spearman": spearman_matrix[target_col],
}).drop(index=target_col)
target_corr["Spearman - Pearson"] = target_corr["Spearman"] - target_corr["Pearson"]
target_corr = target_corr.sort_values("Spearman", ascending=False)
display(target_corr)

target_corr_plot_df = target_corr.reset_index()
target_corr_plot_df.columns = ["Feature", "Pearson", "Spearman", "Spearman - Pearson"]

fig = px.bar(
    target_corr_plot_df,
    x="Feature",
    y=["Pearson", "Spearman"],
    barmode="group",
    title=f"Correlation of each feature with {target_col}",
    labels={"value": "Correlation", "variable": "Method"},
)
fig.update_layout(xaxis_tickangle=-45)
show_plotly(fig)

,Pearson,Spearman,Spearman - Pearson
Demand Forecast,0.997,0.994,-0.003
Inventory Level,0.590,0.568,-0.022
Discount,0.003,0.003,0.001
Holiday/Promotion,-0.000,0.001,0.001
Competitor Pricing,0.001,0.000,-0.001
Price,0.001,0.000,-0.001
Units Ordered,-0.001,-0.001,0.000


Remarks: Those near-zero values aren’t a calculation error. The five variables (Discount, Holiday/Promotion, Competitor Pricing, Price, Units Ordered) really have no relationship with Units Sold in this dataset. The most likely reason is that the data was generated synthetically, with these columns created independently of sales.

## 6. Step 5 — Understand relationships among variables (multivariate analysis)

Multivariate analysis asks whether variables move together, form groups, or interact.

### 6.1 Interactive scatter plot — own price vs. competitor price

Retailers often set prices relative to competitors. This plot checks how closely `Price` and `Competitor Pricing` move together. A very tight relationship would mean the two variables carry almost the same information (**multicollinearity**). Random sample of `SCATTER_MAX_ROWS` rows, for the chart only.

In [34]:
scatter_x = "Price"
scatter_y = "Competitor Pricing"

# Colour by the product category.
scatter_hue = group_col

if scatter_x is None or scatter_y is None:
    print("At least two numerical variables are required for a scatter plot.")
else:
    # Plotting copy only: a random sample keeps the interactive chart responsive.
    plot_df = df.sample(
        min(SCATTER_MAX_ROWS, len(df)),
        random_state=42,
    ).copy()

    if scatter_hue is not None:
        # Cast to strings so Plotly treats them as categories and provides a categorical legend.
        plot_df[scatter_hue] = plot_df[scatter_hue].astype("string").fillna("<Missing>")

    fig = px.scatter(
        plot_df,
        x=scatter_x,
        y=scatter_y,
        color=scatter_hue,
        opacity=0.7,
        title=f"{scatter_y} vs. {scatter_x}",
        hover_data=[c for c in ["Store ID", "Product ID", hue_col] if c is not None and c in plot_df.columns],
    )
    show_plotly(fig)

### 6.2 Interactive pair plot — inventory, forecast, pricing, and sales

Rows are sampled **only for visualization** (max. 1,500 rows). The selected variables are the two strongest correlates of the target (`Inventory Level`, `Demand Forecast`), the two main commercial levers (`Price`, `Discount`), and the target itself.

In [35]:
pair_columns = [
    "Inventory Level",
    "Demand Forecast",
    "Price",
    "Discount",
    target_col,
]

if len(pair_columns) < 2:
    print("At least two numerical variables are required for a pair plot.")
else:
    pair_df = df.sample(
        min(PAIRPLOT_MAX_ROWS, len(df)),
        random_state=42,
    ).copy()

    # Use a categorical color only when the candidate has a manageable
    # number of classes.
    pair_hue = None
    candidate_hue = group_col
    if (
        candidate_hue in pair_df.columns
        and pair_df[candidate_hue].nunique(dropna=True) <= 10
    ):
        pair_hue = candidate_hue
        pair_df[pair_hue] = pair_df[pair_hue].astype("string").fillna("<Missing>")

    fig = px.scatter_matrix(
        pair_df,
        dimensions=pair_columns,
        color=pair_hue,
        title="Interactive Pair Plot",
        opacity=0.55,
    )
    fig.update_traces(diagonal_visible=False)
    fig.update_layout(height=900)
    show_plotly(fig)

**Remarks — pair plot (sample of 1,500 rows, coloured by `Category`)**

- **`Demand Forecast` vs. `Units Sold`:** a thin diagonal line, the clearest pattern in the matrix. The forecast follows actual sales almost exactly, which again points to possible target leakage.
- **`Inventory Level` vs. `Units Sold` (and vs. `Demand Forecast`):** a triangle-shaped cloud. Sales and forecast stay below the stock level but are otherwise spread evenly beneath it, so inventory works as a ceiling rather than a linear driver.
- **`Price` panels:** square, evenly filled clouds against every other variable. Price is unrelated to sales, inventory, or forecast. There is no visible demand curve.
- **`Discount` panels:** vertical or horizontal stripes at the five discount levels, each covering the full range of the other variable. Discounts do not shift sales or prices.
- **Categories:** the colours are completely mixed in every panel. No category forms its own cluster or follows a different pattern.

**Overall:** the pair plot confirms the earlier findings in one view. Only the forecast and inventory relate to sales; all other relationships look random, as expected for a synthetic dataset.

### 6.3 Focused scatter-plot matrix — pricing and replenishment

Without colour, this matrix concentrates on how the pricing and replenishment variables relate to each other (`Price`, `Competitor Pricing`, `Discount`, `Units Ordered`). Strong mutual relationships here would indicate **multicollinearity** to keep in mind for a linear model.

In [36]:
scatter_matrix_columns = [
    "Price",
    "Competitor Pricing",
    "Discount",
    "Units Ordered",
]

if len(scatter_matrix_columns) < 2:
    print("At least two numerical variables are required for a scatter matrix.")
else:
    matrix_df = df[scatter_matrix_columns].dropna()   # plotting copy only

    if len(matrix_df) > PAIRPLOT_MAX_ROWS:
        matrix_df = matrix_df.sample(PAIRPLOT_MAX_ROWS, random_state=42)

    fig = px.scatter_matrix(
        matrix_df,
        dimensions=scatter_matrix_columns,
        title="Focused Scatter-Plot Matrix",
        opacity=0.55,
    )
    fig.update_traces(diagonal_visible=False)
    fig.update_layout(height=750)
    show_plotly(fig)

### 6.4 Interactive correlation heatmaps

- **Pearson:** linear association.
- **Spearman:** monotonic association based on ranks.
- **Kendall:** rank concordance, often useful with many tied ranks (e.g. `Discount`, `Holiday/Promotion`).

All 73,100 rows are used. Remember: **correlation does not imply causation**.

> Kendall's coefficient is slower to compute than Pearson/Spearman; with 73,100 rows this cell may take a little longer.

In [37]:
if len(numeric_columns) < 2:
    print("At least two numerical variables are required for correlation analysis.")
else:
    for method, label in [
        ("pearson", "Pearson"),
        ("spearman", "Spearman"),
        ("kendall", "Kendall"),
    ]:
        correlation_matrix = df[numeric_columns].corr(method=method)

        fig = px.imshow(
            correlation_matrix,
            text_auto=".2f",
            aspect="auto",
            zmin=-1,
            zmax=1,
            color_continuous_scale="RdBu_r",
            title=f"{label} Correlation Heatmap",
            labels={"color": "Correlation"},
        )
        fig.update_layout(height=750)
        show_plotly(fig)

**Remarks — Pearson, Spearman, and Kendall correlation heatmaps**

- **Only three dark cells stand out; the rest of the matrix is blank.** All three heatmaps show the same picture. Almost every pair of variables has a correlation of ≈ 0.00, and only three relationships are clearly visible:
  - **`Units Sold` ↔ `Demand Forecast`** (≈ 1.00 / 0.99 / 0.94): the forecast is practically a copy of actual sales, a strong sign of **target leakage**.
  - **`Price` ↔ `Competitor Pricing`** (≈ 0.99 / 0.99 / 0.93): the two prices move together almost perfectly. Using both in a linear model would cause **multicollinearity**, so keeping one of them, or their difference, is enough.
  - **`Inventory Level` ↔ `Units Sold` and `Demand Forecast`** (≈ 0.59 / 0.57 / 0.41): a moderate positive relationship. Higher stock goes with higher sales, but as the scatter plots show, inventory acts as a ceiling rather than a straight-line driver.
- **The three methods agree.** Pearson and Spearman are almost identical everywhere, so the relationships are not distorted by outliers or hidden nonlinear (monotonic) patterns. Kendall values are lower overall, which is a normal property of that coefficient, not a weaker effect.
- **No negative correlations.** There are no blue cells, so no variable decreases as another increases. Price does not lower sales, and discounts or promotions do not raise them, contrary to what retail theory would predict.

**Overall:** apart from the leakage-prone forecast, inventory is the only meaningful predictor of sales, and the two price variables are redundant. The almost empty matrix confirms that most features were generated independently of each other.

### 6.5 Interactive parallel-coordinates plot

Each line is one sampled store–product–day (max. 500). Lines are **coloured by units sold**, so you can drag a range on the `Units Sold` axis (e.g. the top values) and see which inventory, order, price, and discount levels those high-sales days share.

In [38]:
parallel_columns = [
    "Inventory Level",
    "Units Ordered",
    "Price",
    "Discount",
    target_col,
]

if len(parallel_columns) < 2:
    print("At least two numerical variables are required for parallel coordinates.")
else:
    # Keep the plot readable and responsive by limiting displayed rows (plotting copy only).
    parallel_df = df[parallel_columns].dropna()
    if len(parallel_df) > 500:
        parallel_df = parallel_df.sample(500, random_state=42)
    parallel_df = parallel_df.copy()

    # The target is continuous, so it can be used directly as the colour axis.
    color_column = target_col

    fig = px.parallel_coordinates(
        parallel_df,
        dimensions=parallel_columns,
        color=color_column,
        title="Interactive Parallel Coordinates (colour = units sold)",
    )
    fig.update_layout(height=550)
    show_plotly(fig)

### 6.6 Interactive bubble chart — inventory × price × sales

Here x = inventory level, y = units sold (target), bubble size = price, colour = category. If large bubbles (expensive products) sat systematically lower than small ones at the same inventory level, price would modify the inventory–sales relationship — an interaction. Random sample of `SCATTER_MAX_ROWS` rows, for the chart only.

In [39]:
bubble_x = "Inventory Level"
bubble_y = target_col
bubble_size = "Price"

bubble_color = group_col

needed_columns = [bubble_x, bubble_y, bubble_size]
if bubble_color is not None:
    needed_columns.append(bubble_color)

# Plotting copy only — rows with a missing x/y/size cannot be drawn.
bubble_df = df[needed_columns].dropna(subset=[bubble_x, bubble_y, bubble_size]).copy()

# A random sample keeps the interactive chart readable and responsive.
if len(bubble_df) > SCATTER_MAX_ROWS:
    bubble_df = bubble_df.sample(SCATTER_MAX_ROWS, random_state=42)

# Plotly requires non-negative bubble sizes.
bubble_df["_bubble_size_"] = bubble_df[bubble_size].abs()

if bubble_color is not None:
    bubble_df[bubble_color] = bubble_df[bubble_color].astype("string").fillna("<Missing>")

fig = px.scatter(
    bubble_df,
    x=bubble_x,
    y=bubble_y,
    size="_bubble_size_",
    color=bubble_color,
    hover_data={bubble_size: True, "_bubble_size_": False},
    size_max=20,
    opacity=0.6,
    title=f"Bubble Chart: {bubble_x}, {bubble_y}, size = {bubble_size}",
)
show_plotly(fig)

## 7. Step 6 — Association between categorical variables (Chi-square test & Cramér's V)

Correlation coefficients only work for numerical variables. For two **categorical** variables we use the procedure from `Cramers.ipynb`:

1. build a frequency (contingency) table with `pd.crosstab`,
2. run a Pearson Chi-square test with `researchpy.crosstab(..., test="chi-square")`, which also reports **Cramér's V** (0 = no association, 1 = perfect association),
3. compute the degrees of freedom to interpret the size of Cramér's V with a lookup table.

We test five pairs:

| Pair | Question |
|---|---|
| `Category` × `Region` | Are certain product categories sold mainly in certain regions? |
| `Weather Condition` × `Seasonality` | Does the weather depend on the season (e.g. snow mainly in winter)? A plausibility check. |
| `Product ID` × `Category` | Does each product always belong to exactly one category (a consistency check)? |
| `Store ID` × `Region` | Is each store always located in exactly one region (a consistency check)? |
| `Seasonality` × `Holiday/Promotion` | Are holidays/promotions concentrated in certain seasons? |

> `researchpy` may print a pandas `FutureWarning` (also visible in `Cramers.ipynb`). It is harmless and does not affect the results.

In [40]:
categorical_pairs = [
    ("Category", "Region"),
    ("Weather Condition", "Seasonality"),
    ("Product ID", "Category"),
    ("Store ID", "Region"),
    ("Seasonality", "Holiday/Promotion"),
]

### 7.1 Frequency tables

In [41]:
for row_var, col_var in categorical_pairs:
    print(f"\n=== {row_var} x {col_var} ===")
    # Get the count/frequency
    contTable = pd.crosstab(df[row_var], df[col_var])
    display(contTable)


=== Category x Region ===


Region,East,North,South,West
Category,,,,
Clothing,3753,3528,3651,3694
Electronics,3705,3589,3606,3621
Furniture,3607,3720,3684,3688
Groceries,3684,3652,3704,3571
Toys,3600,3739,3652,3652



=== Weather Condition x Seasonality ===


Seasonality,Autumn,Spring,Summer,Winter
Weather Condition,,,,
Cloudy,4503,4677,4523,4557
Rainy,4591,4567,4612,4508
Snowy,4593,4475,4622,4582
Sunny,4506,4598,4548,4638



=== Product ID x Category ===


Category,Clothing,Electronics,Furniture,Groceries,Toys
Product ID,,,,,
P0001,744,700,720,763,728
P0002,718,727,753,729,728
P0003,717,689,735,759,755
P0004,711,747,725,727,745
P0005,697,743,740,754,721
P0006,731,720,702,777,725
P0007,740,762,736,696,721
P0008,755,758,733,681,728
P0009,766,675,770,721,723



=== Store ID x Region ===


Region,East,North,South,West
Store ID,,,,
S001,3675,3637,3663,3645
S002,3749,3622,3671,3578
S003,3636,3669,3678,3637
S004,3620,3662,3621,3717
S005,3669,3638,3664,3649



=== Seasonality x Holiday/Promotion ===


Holiday/Promotion,0,1
Seasonality,,
Autumn,9165,9028
Spring,9149,9168
Summer,9217,9088
Winter,9216,9069


### 7.2 Run Chi-square and Cramér's V

In [42]:
cramers_summary = []

for row_var, col_var in categorical_pairs:
    print(f"\n=== {row_var} x {col_var} ===")
    crosstab, results = researchpy.crosstab(df[row_var], df[col_var], test='chi-square')
    display(results)
    print("Cramer's V:", results.loc[2]['results'])

    cramers_summary.append({
        "pair": f"{row_var} x {col_var}",
        "chi_square": results.loc[0]['results'],
        "p_value": results.loc[1]['results'],
        "cramers_v": results.loc[2]['results'],
    })


=== Category x Region ===


,Chi-square test,results
0,Pearson Chi-square (12) =,16.484
1,p-value =,0.170
2,Cramer's V =,0.009


Cramer's V: 0.0087

=== Weather Condition x Seasonality ===


,Chi-square test,results
0,Pearson Chi-square (9) =,9.680
1,p-value =,0.377
2,Cramer's V =,0.007


Cramer's V: 0.0066

=== Product ID x Category ===


...

Cramer's V: 0.0165

=== Store ID x Region ===


,Chi-square test,results
0,Pearson Chi-square (12) =,6.336
1,p-value =,0.898
2,Cramer's V =,0.005


Cramer's V: 0.0054

=== Seasonality x Holiday/Promotion ===


,Chi-square test,results
0,Pearson Chi-square (3) =,1.019
1,p-value =,0.797
2,Cramer's V =,0.004


Cramer's V: 0.0037


### 7.3 Calculate degrees of freedom

As in `Cramers.ipynb`, the degrees of freedom are `dof = (r-1)(c-1)`. Many published lookup tables for the size of Cramér's V (Cohen, 1988) are indexed by `df* = min(r-1, c-1)`, so both values are shown.

| df* | small | medium | large |
|---|---|---|---|
| 1 | 0.10 | 0.30 | 0.50 |
| 2 | 0.07 | 0.21 | 0.35 |
| 3 | 0.06 | 0.17 | 0.29 |
| 4 | 0.05 | 0.15 | 0.25 |
| 5 | 0.04 | 0.13 | 0.22 |

In [43]:
for i, (row_var, col_var) in enumerate(categorical_pairs):
    contTable = pd.crosstab(df[row_var], df[col_var])
    dof = (contTable.shape[0]-1)*(contTable.shape[1]-1)
    cramers_summary[i]["table_shape"] = contTable.shape
    cramers_summary[i]["dof"] = dof
    cramers_summary[i]["df_star_min(r-1,c-1)"] = min(contTable.shape) - 1

display(pd.DataFrame(cramers_summary))

,pair,chi_square,p_value,cramers_v,table_shape,dof,"df_star_min(r-1,c-1)"
0,Category x Region,16.484,0.170,0.009,"(5, 4)",12,3
1,Weather Condition x Seasonality,9.680,0.377,0.007,"(4, 4)",9,3
2,Product ID x Category,79.968,0.356,0.017,"(20, 5)",76,4
3,Store ID x Region,6.336,0.898,0.005,"(5, 4)",12,3
4,Seasonality x Holiday/Promotion,1.019,0.797,0.004,"(4, 2)",3,1


**Remarks — Chi-square test and Cramér's V**

- **No pair of categorical variables is associated.** All five Cramér's V values are close to 0 (≤ 0.02), far below even the "small" threshold of the lookup table. All p-values are well above 0.05, so none of the associations is statistically significant.
- **`Category` × `Region` and `Seasonality` × `Holiday/Promotion`:** no association. Every category is sold equally in every region, and promotions are spread evenly across the seasons. Both results are plausible for a balanced dataset.
- **`Weather Condition` × `Seasonality`:** no association, which is **not plausible**. In reality, snow should occur mainly in winter and sunny days mainly in summer. The weather labels appear to be assigned randomly.
- **`Product ID` × `Category` and `Store ID` × `Region`:** these consistency checks should give a Cramér's V close to **1**, since a product normally belongs to one category and a store to one region. Instead, the values are ≈ 0: every product appears in all five categories and every store in all four regions. This is a **major data-consistency issue**. `Category` and `Region` do not describe fixed attributes of products and stores.

**Overall:** the categorical variables are independent of each other, even where a strong link would be expected. This confirms that the labels were generated randomly. `Category`, `Region`, `Weather Condition`, and `Seasonality` should be interpreted with great caution, and their meaning clarified before they are used for modelling.

**Interpretation (results observed when this notebook was prepared):**

- **`Category` × `Region`:** Cramér's V ≈ 0.009 with p ≈ 0.17 → no significant association; every category is sold about equally often in every region.
- **`Weather Condition` × `Seasonality`:** Cramér's V ≈ 0.007 with p ≈ 0.38 → no association. Snowy days are as frequent in "Summer" as in "Winter". In real data we would expect a clear association, so the weather and season labels look **randomly assigned** and are unlikely to carry real seasonal information.
- **`Product ID` × `Category`:** Cramér's V ≈ 0.017 (p ≈ 0.36), although a consistency check would expect a value close to 1. The frequency table shows that **every product appears in all five categories** — `Category` is not a fixed attribute of the product. This is a major data-consistency issue to clarify before modelling.
- **`Store ID` × `Region`:** Cramér's V ≈ 0.005 (p ≈ 0.90). **Every store appears in all four regions**, so `Region` is not a fixed attribute of the store either.
- **`Seasonality` × `Holiday/Promotion`:** Cramér's V ≈ 0.004 with p ≈ 0.80 → promotions are spread evenly over the seasons.

All Cramér's V values are far below the "small" threshold of the lookup table, so the conclusions are the same whichever df convention is used.

## 8. Step 7 — Summary of the EDA

The findings below describe the results observed when this notebook was prepared. **Nothing was removed or changed in the dataset**; the points are recommendations for the later data-preparation and modelling steps.

### 8.1 What does one row represent?
One product (`Product ID`, 20 products) in one store (`Store ID`, 5 stores) on one day (`Date`, 731 days from 1 Jan 2022 to 1 Jan 2024) — 73,100 rows and 15 columns. Every store–day contains exactly the 20 products, i.e. the panel is complete (100 rows per day). Note that 1 Jan 2024 is the only day of 2024.

### 8.2 Data-quality issues to treat later

| Issue | Observation | Possible treatment (later) |
|---|---|---|
| Missing values | None in any column. | — |
| Duplicates | No duplicate rows and no repeated `Date` + `Store ID` + `Product ID` keys. | — |
| Negative forecasts | 673 rows (≈0.9%) have a negative `Demand Forecast` (down to −9.99). These rows all have very low sales (0–9 units). | Clip at 0 or treat as invalid, if the forecast is used at all. |
| Inconsistent product attributes | Every `Product ID` appears in **all 5 categories** (Section 7). | Clarify with the data owner what `Category` and `Product ID` mean; do not rely on `Product ID` → `Category` mapping. |
| Inconsistent store attributes | Every `Store ID` appears in **all 4 regions** (Section 7). | Clarify what `Region` describes (store location, customer region, delivery region?). |
| Implausible external labels | `Seasonality` is not linked to the calendar month and `Weather Condition` is independent of the season; the weather can differ between products of the same store on the same day. | Derive season from `Date` instead; treat weather with caution. |
| Units Sold vs. inventory | No row sells more than its inventory (rule respected); 360 rows have zero sales. | Keep; zero sales are plausible. |

The dataset is described as *cleaned*, and indeed there are no missing values or duplicates. However, the label inconsistencies and the very uniform distributions (Section 8.3) indicate a **synthetic dataset**, which strongly affects what a model can learn from it.

### 8.3 Distributions
- All categorical variables are almost perfectly balanced (each store 20%, each product 5%, each category/region/weather/season ≈ 20–25%); `Holiday/Promotion` is ≈ 50% / 50%; each `Discount` level ≈ 20%.
- `Inventory Level` (50–500), `Units Ordered` (20–200), `Price` (10–100), and `Competitor Pricing` look **uniformly distributed** (skewness ≈ 0, kurtosis ≈ −1.2), which is unusual for real retail data.
- `Units Sold` (0–499; median 107, mean 136) and `Demand Forecast` are **moderately right-skewed** (skewness ≈ 0.9). About 240 rows per variable have |z| > 3 (very high sales days); no other variable has z-score outliers.

### 8.4 Which variables relate to units sold?
- **`Demand Forecast`** has an almost perfect correlation with the target (Pearson ≈ 0.997, Spearman ≈ 0.994); it differs from `Units Sold` by only about −10 to +20 units. Such a close match is a strong signal of **target leakage**: unless the forecast is truly available *before* the sales day, it must not be used as a predictor (and should at least be modelled separately as a benchmark).
- **`Inventory Level`** is the only other relevant variable (Pearson ≈ 0.59, Spearman ≈ 0.57). The scatter plot shows a **triangle**: units sold never exceed inventory, and the share of inventory sold is spread evenly between 0 and 100%. Inventory therefore acts as an **upper bound** on sales rather than a linear driver.
- `Price`, `Discount`, `Competitor Pricing`, `Holiday/Promotion`, and `Units Ordered` show **no correlation** with the target (|r| < 0.01), and the box plots of the target by `Category`, `Region`, `Weather Condition`, `Seasonality`, `Store ID`, `Holiday/Promotion`, and `Discount` are practically identical (group means between ≈135 and ≈138 units).
- `Price` and `Competitor Pricing` are almost identical (r ≈ 0.994; the competitor price lies within ±5 of the own price) → strong **multicollinearity**; keep only one or use their difference.

### 8.5 Relationships that need further (causal / domain) validation
- The absence of any price, discount, or promotion effect contradicts basic retail economics; it should be verified with the data owner before concluding that these levers do not matter.
- How `Demand Forecast` was produced (timing and method) must be clarified before it is used.
- Whether inventory limits sales (stock-outs, censored demand) or whether stores simply stock more of what sells — the direction of the inventory–sales relationship cannot be determined from correlation alone.
- Weak linear correlation does **not** mean "irrelevant": possible interactions (e.g. discount × category) should be checked in the modelling phase.

### 8.6 What additional data would improve the analysis?
Real product master data (fixed category per product, product prices/costs), store master data (fixed location, size), stock-out flags or lost-sales estimates, the timing and method of the demand forecast, actual promotion calendars, and real weather data per store location and day.

### 8.7 Open questions for the modelling phase
1. May `Demand Forecast` be used as a feature (leakage), or only as a benchmark to beat?
2. Should calendar features (weekday, month, season) be derived from `Date` instead of using the `Seasonality` label?
3. How should the inventory upper bound be handled — e.g. by modelling the share of inventory sold, or by treating sales as censored demand?
4. Should `Store ID` and `Product ID` be used as features, or only for grouping / cross-validation (e.g. grouped by time to avoid leakage between days)?

### Final check — the dataset was not modified

In [44]:
print("Shape when loaded :", ORIGINAL_SHAPE)
print("Shape now         :", df.shape)
print("No rows or columns were removed:", ORIGINAL_SHAPE == df.shape)

Shape when loaded : (73100, 15)
Shape now         : (73100, 15)
No rows or columns were removed: True


## Brainstorming


## Brainstorming — Hypotheses derived from the EDA

The table turns the patterns found in the plots into testable hypotheses. Each verdict is based on **exploratory evidence only**. Correlation does not imply causation, and every hypothesis should be confirmed during modelling or with domain experts.

| # | Hypothesis | Involved variables | Evidence from the plots | Verdict |
|---|---|---|---|---|
| H1 | The existing demand forecast predicts sales almost perfectly, which suggests **target leakage** (the forecast may have been created after sales were known). | `Demand Forecast`, `Units Sold` | The scatter plot and pair plot show a thin diagonal line. The correlation heatmaps give ≈ 1.00 (Pearson), 0.99 (Spearman), and 0.94 (Kendall). The box plots, histograms, and z-score outlier counts of both variables are almost identical. | **Supported**, but the forecast's origin must be verified before it is used as a feature |
| H2 | Inventory acts as an **upper limit** on sales rather than a linear driver: high stock allows high sales but does not guarantee them. | `Inventory Level`, `Units Sold` | The scatter plot shows a triangle-shaped cloud with no point above the diagonal (sales never exceed stock). The heatmaps show a moderate correlation (≈ 0.59 Pearson / 0.57 Spearman). | **Supported** |
| H3 | Higher prices **reduce** the number of units sold (a downward-sloping demand curve). | `Price`, `Competitor Pricing`, `Units Sold` | The scatter plots and pair plot show flat, square clouds. All correlations are ≈ 0.00, and no negative (blue) cells appear in the heatmaps. | **Not supported** |
| H4 | Discounts and holiday/promotion days **increase** sales. | `Discount`, `Holiday/Promotion`, `Units Sold` | The scatter plots show vertical stripes covering the same range of sales at every level. The box plots of `Units Sold` by discount level and by promotion day are practically identical. Correlations are ≈ 0.00. | **Not supported** |
| H5 | Our price and the competitor's price carry the **same information** (multicollinearity). | `Price`, `Competitor Pricing` | The scatter plot shows a tight band along the diagonal (difference within ±5). The heatmaps show ≈ 0.99 (Pearson and Spearman). Grouped box and violin plots look the same for both. | **Supported**: keep only one, or use the price difference |
| H6 | Replenishment orders **follow demand**: more units are ordered for products that sell more or have low stock. | `Units Ordered`, `Units Sold`, `Inventory Level`, `Demand Forecast` | The scatter plot of `Units Ordered` vs. `Units Sold` is a flat cloud. Correlations with sales, forecast, and inventory are all ≈ 0.00. Orders are uniformly distributed (flat histogram and rectangular violin). | **Not supported**: no visible replenishment policy |
| H7 | Sales levels **differ by product category and region** (e.g. groceries sell more units than furniture). | `Category`, `Region`, `Units Sold` | Grouped box plots, violin plots, and region-coloured histograms are practically identical for all groups. Cramér's V for `Category` × `Region` is ≈ 0.01. | **Not supported** |
| H8 | **Weather and season** influence sales (e.g. fewer store visits on snowy days, seasonal peaks). | `Weather Condition`, `Seasonality`, `Units Sold` | The box plots of `Units Sold` by weather and season show the same distribution in every group. Cramér's V for `Weather Condition` × `Seasonality` is ≈ 0.007, so even snow is not linked to winter, and the labels appear random. | **Not supported**: labels are likely synthetic |

**Takeaway:** only H1, H2, and H5 are supported by the plots. The economically expected effects of price, promotions, replenishment, category, region, weather, and season (H3, H4, H6–H8) do not appear in this dataset. This is consistent with the earlier finding that the data is largely synthetic. For modelling, the key decisions are therefore how to handle the leakage-prone `Demand Forecast` (H1), how to model the inventory ceiling (H2), and which of the two price variables to keep (H5).